# Step 1
The combinations of gas mixture combinations:

0 represents the gas concentration (ppm = 0) zero/not present
1 represents the gas concentration (ppm > 0) is present

|e|m|
|--|--|
|0|0|
|0|1|
|1|1|
|1|0|

# Data Preprocessing and Ploting

In [ ]:
import numpy as np
# Load raw data (skip header row)
emraw = np.loadtxt(
    r"filepath\filename.csv",   # copy file path and insert within quotes
    skiprows=1
)
data = np.array(emraw)
chunk_size = 100
n_rows = data.shape[0]

# Assume first 3 columns are metadata (x1, col1, col2, etc.)
meta_cols = data[:, :3]   # non-sensor columns
y_cols = data[:, 3:]      # sensor readings

n_chunks = (n_rows + chunk_size - 1) // chunk_size

# Prepare results: start/end for each meta column + m/c pairs for sensors
results = np.zeros((n_chunks, 2*meta_cols.shape[1] + 2*y_cols.shape[1]))

for i in range(n_chunks):
    start = i * chunk_size
    end = min(start + chunk_size, n_rows)

    # Store start and end for each meta column
    for k in range(meta_cols.shape[1]):
        results[i, 2*k]   = meta_cols[start, k]   # start value
        results[i, 2*k+1] = meta_cols[end-1, k]   # end value

    # Fit each sensor column
    x_chunk = meta_cols[start:end, 0]  # use first meta column (x1) as x
    for j, y_col in enumerate(y_cols.T):
        y_chunk = y_col[start:end]
        m, c = np.polyfit(x_chunk, y_chunk, deg=1)
        results[i, 2*meta_cols.shape[1] + 2*j] = m
        results[i, 2*meta_cols.shape[1] + 2*j+1] = c

# Build column names
col_names = []
for k in range(meta_cols.shape[1]):
    col_names += [f"start_col{k+1}", f"end_col{k+1}"]
for j in range(y_cols.shape[1]):
    col_names += [f"m_y{j+1}", f"c_y{j+1}"]

# Save with header
np.savetxt(
    "1_em_fit.csv",
    results,
    delimiter=",",
    header=",".join(col_names),
    comments="",
    fmt="%.6f"
)
print(f"Shape of Original Data: {data.shape}")
print(f"Column Names: {col_names}")
print(f"Fitted Results:\n{results}")

Shape of Original Data: (4178504, 19)
Column Names: ['start_col1', 'end_col1', 'start_col2', 'end_col2', 'start_col3', 'end_col3', 'm_y1', 'c_y1', 'm_y2', 'c_y2', 'm_y3', 'c_y3', 'm_y4', 'c_y4', 'm_y5', 'c_y5', 'm_y6', 'c_y6', 'm_y7', 'c_y7', 'm_y8', 'c_y8', 'm_y9', 'c_y9', 'm_y10', 'c_y10', 'm_y11', 'c_y11', 'm_y12', 'c_y12', 'm_y13', 'c_y13', 'm_y14', 'c_y14', 'm_y15', 'c_y15', 'm_y16', 'c_y16']
Fitted Results:
[[ 0.00000000e+00  9.90000000e-01  0.00000000e+00 ...  3.64981170e+03
   6.40932493e+00  3.12676038e+03]
 [ 1.00000000e+00  1.99000000e+00  0.00000000e+00 ...  3.64010233e+03
  -2.99543954e-01  3.12767932e+03]
 [ 2.00000000e+00  2.99000000e+00  0.00000000e+00 ...  3.64803425e+03
  -6.41092709e+00  3.14545076e+03]
 ...
 [ 4.17881600e+04  4.17891500e+04  0.00000000e+00 ... -1.01699331e+06
   1.84857486e+01 -7.71587075e+05]
 [ 4.17891600e+04  4.17901500e+04  0.00000000e+00 ... -1.28781274e+06
   2.00666667e+01 -8.37653468e+05]
 [ 4.17901600e+04  4.17901900e+04  0.00000000e+00 ...

In [78]:
print(f"Shape of Original Data: {data.shape}")

print(f"Shape of Fitted Results: {results.shape}")

Shape of Original Data: (4178504, 19)
Shape of Fitted Results: (41786, 38)


In [79]:
import pandas as pd

# Define your new column names
col_names = [
    "TimeStart(seconds)", "TimeEnd(seconds)",
    "MethConcStart(ppm)", "MethConcEnd(ppm)", 
    "EthyConcStart(ppm)", "EthyConcEnd(ppm)",
    "Sensor-2-1(m)", "Sensor-2-1(C)", 
    "Sensor-2-2(m)", "Sensor-2-2(C)",
    "Sensor-1-1(m)", "Sensor-1-1(C)", 
    "Sensor-1-2(m)", "Sensor-1-2(C)",
    "Sensor-3-1(m)", "Sensor-3-1(C)", 
    "Sensor-3-2(m)", "Sensor-3-2(C)", 
    "Sensor-4-1(m)", "Sensor-4-1(C)", 
    "Sensor-4-2(m)", "Sensor-4-2(C)",
    "Sensor-2-3(m)", "Sensor-2-3(C)",
    "Sensor-2-4(m)", "Sensor-2-4(C)",
    "Sensor-1-3(m)", "Sensor-1-3(C)",
    "Sensor-1-4(m)", "Sensor-1-4(C)",
    "Sensor-3-3(m)", "Sensor-3-3(C)",
    "Sensor-3-4(m)", "Sensor-3-4(C)",
    "Sensor-4-3(m)", "Sensor-4-3(C)",
    "Sensor-4-4(m)", "Sensor-4-4(C)"
]

# Load your dataset and assign new headers
emfit = pd.read_csv("1_em_fit.csv", header=0, names=col_names)

# ✅ 1. DataFrame info (structure, dtypes, non-null counts, memory usage)
print("=== DataFrame Info ===")
print(emfit.info())


=== DataFrame Info ===
<class 'pandas.DataFrame'>
RangeIndex: 41786 entries, 0 to 41785
Data columns (total 38 columns):
 #   Column              Non-Null Count  Dtype  
---  ------              --------------  -----  
 0   TimeStart(seconds)  41786 non-null  float64
 1   TimeEnd(seconds)    41786 non-null  float64
 2   MethConcStart(ppm)  41786 non-null  float64
 3   MethConcEnd(ppm)    41786 non-null  float64
 4   EthyConcStart(ppm)  41786 non-null  float64
 5   EthyConcEnd(ppm)    41786 non-null  float64
 6   Sensor-2-1(m)       41786 non-null  float64
 7   Sensor-2-1(C)       41786 non-null  float64
 8   Sensor-2-2(m)       41786 non-null  float64
 9   Sensor-2-2(C)       41786 non-null  float64
 10  Sensor-1-1(m)       41786 non-null  float64
 11  Sensor-1-1(C)       41786 non-null  float64
 12  Sensor-1-2(m)       41786 non-null  float64
 13  Sensor-1-2(C)       41786 non-null  float64
 14  Sensor-3-1(m)       41786 non-null  float64
 15  Sensor-3-1(C)       41786 non-null  float

### Descriptive statistics (numeric columns by default)


In [80]:

print("\n=== Numeric Descriptive Statistics ===")
print(emfit.describe())



=== Numeric Descriptive Statistics ===
       TimeStart(seconds)  TimeEnd(seconds)  MethConcStart(ppm)  \
count        41786.000000      41786.000000        41786.000000   
mean         20895.641402      20896.631276           58.085006   
std          12064.459535      12064.459267           76.639946   
min              0.000000          0.990000            0.000000   
25%          10446.710000      10447.700000            0.000000   
50%          20896.700000      20897.690000            0.000000   
75%          31343.220000      31344.210000          100.000000   
max          41790.160000      41790.190000          296.670000   

       MethConcEnd(ppm)  EthyConcStart(ppm)  EthyConcEnd(ppm)  Sensor-2-1(m)  \
count      41786.000000        41786.000000      41786.000000   41786.000000   
mean          58.081815            4.369478          4.369478       0.053684   
std           76.639589            5.521364          5.521364       7.270395   
min            0.000000            0

## Keep only the desired columns

In [81]:
import pandas as pd

# Define new column names
col_names = [
    "TimeStart(seconds)", "TimeEnd(seconds)",
    "MethConcStart(ppm)", "MethConcEnd(ppm)", 
    "EthyConcStart(ppm)", "EthyConcEnd(ppm)",
    "Sensor-2-1(m)", "Sensor-2-1(C)", 
    "Sensor-2-2(m)", "Sensor-2-2(C)",
    "Sensor-1-1(m)", "Sensor-1-1(C)", 
    "Sensor-1-2(m)", "Sensor-1-2(C)",
    "Sensor-3-1(m)", "Sensor-3-1(C)", 
    "Sensor-3-2(m)", "Sensor-3-2(C)", 
    "Sensor-4-1(m)", "Sensor-4-1(C)", 
    "Sensor-4-2(m)", "Sensor-4-2(C)",
    "Sensor-2-3(m)", "Sensor-2-3(C)",
    "Sensor-2-4(m)", "Sensor-2-4(C)",
    "Sensor-1-3(m)", "Sensor-1-3(C)",
    "Sensor-1-4(m)", "Sensor-1-4(C)",
    "Sensor-3-3(m)", "Sensor-3-3(C)",
    "Sensor-3-4(m)", "Sensor-3-4(C)",
    "Sensor-4-3(m)", "Sensor-4-3(C)",
    "Sensor-4-4(m)", "Sensor-4-4(C)"
]

# Load dataset, ignore original header row, assign new headers
em_fit = pd.read_csv("1_em_fit.csv", header=0, names=col_names)

# Define columns to drop
drop_cols_list = [
    "TimeEnd(seconds)", 
    "MethConcEnd(ppm)", 
    "EthyConcEnd(ppm)",
    # "Sensor-2-2(m)",  # faulty column
    # drop all slope (c) columns
    "Sensor-2-1(C)", "Sensor-2-2(C)", "Sensor-1-1(C)", "Sensor-1-2(C)",
    "Sensor-3-1(C)", "Sensor-3-2(C)", "Sensor-4-1(C)", "Sensor-4-2(C)",
    "Sensor-2-3(C)", "Sensor-2-4(C)", "Sensor-1-3(C)", "Sensor-1-4(C)",
    "Sensor-3-3(C)", "Sensor-3-4(C)", "Sensor-4-3(C)", "Sensor-4-4(C)"
]

# Drop unwanted columns
df_filtered = em_fit.drop(columns=drop_cols_list)

# Save filtered dataset without index column
df_filtered.to_csv("2_em_filtered.csv", index=False, float_format="%.6f")
print("Filtered dataset saved as '2_em_filtered.csv'.")

Filtered dataset saved as '2_em_filtered.csv'.


##  Processed Dataset Informations

In [82]:
import pandas as pd
df = pd.read_csv("2_em_filtered.csv")
# Quick info and stats
print("=== DataFrame Info ===")
print(df.info())
print("\n=== Descriptive Statistics ===")
print(df.describe())


=== DataFrame Info ===
<class 'pandas.DataFrame'>
RangeIndex: 41786 entries, 0 to 41785
Data columns (total 19 columns):
 #   Column              Non-Null Count  Dtype  
---  ------              --------------  -----  
 0   TimeStart(seconds)  41786 non-null  float64
 1   MethConcStart(ppm)  41786 non-null  float64
 2   EthyConcStart(ppm)  41786 non-null  float64
 3   Sensor-2-1(m)       41786 non-null  float64
 4   Sensor-2-2(m)       41786 non-null  float64
 5   Sensor-1-1(m)       41786 non-null  float64
 6   Sensor-1-2(m)       41786 non-null  float64
 7   Sensor-3-1(m)       41786 non-null  float64
 8   Sensor-3-2(m)       41786 non-null  float64
 9   Sensor-4-1(m)       41786 non-null  float64
 10  Sensor-4-2(m)       41786 non-null  float64
 11  Sensor-2-3(m)       41786 non-null  float64
 12  Sensor-2-4(m)       41786 non-null  float64
 13  Sensor-1-3(m)       41786 non-null  float64
 14  Sensor-1-4(m)       41786 non-null  float64
 15  Sensor-3-3(m)       41786 non-null  float

In [83]:
import pandas as pd
df = pd.read_csv("2_em_filtered.csv")
print("DataFrame head:\n", df.head())
print(df.shape)
print(df.dtypes)
print(df.columns.tolist())

DataFrame head:
    TimeStart(seconds)  MethConcStart(ppm)  EthyConcStart(ppm)  Sensor-2-1(m)  \
0                 0.0                 0.0                 0.0       5.123186   
1                 1.0                 0.0                 0.0      97.207225   
2                 2.0                 0.0                 0.0     297.822190   
3                 3.0                 0.0                 0.0     441.522460   
4                 4.0                 0.0                 0.0     437.330237   

   Sensor-2-2(m)  Sensor-1-1(m)  Sensor-1-2(m)  Sensor-3-1(m)  Sensor-3-2(m)  \
0      -0.913687      25.495452      25.549589      21.906709      29.218962   
1      -0.842436     201.838152     210.673813     162.384512     217.028737   
2      -2.776796     493.650549     537.996592     510.182430     766.893123   
3       1.261848     732.236844     798.656946     851.576466    1208.847915   
4       0.286331     856.113993     939.443144     980.645659    1207.920456   

   Sensor-4-1(m)  Sen

In [84]:
import pandas as pd
em_filtered = pd.read_csv("2_em_filtered.csv")
print(em_filtered.shape)
print(em_filtered.dtypes)
print(em_filtered.columns.tolist())

(41786, 19)
TimeStart(seconds)    float64
MethConcStart(ppm)    float64
EthyConcStart(ppm)    float64
Sensor-2-1(m)         float64
Sensor-2-2(m)         float64
Sensor-1-1(m)         float64
Sensor-1-2(m)         float64
Sensor-3-1(m)         float64
Sensor-3-2(m)         float64
Sensor-4-1(m)         float64
Sensor-4-2(m)         float64
Sensor-2-3(m)         float64
Sensor-2-4(m)         float64
Sensor-1-3(m)         float64
Sensor-1-4(m)         float64
Sensor-3-3(m)         float64
Sensor-3-4(m)         float64
Sensor-4-3(m)         float64
Sensor-4-4(m)         float64
dtype: object
['TimeStart(seconds)', 'MethConcStart(ppm)', 'EthyConcStart(ppm)', 'Sensor-2-1(m)', 'Sensor-2-2(m)', 'Sensor-1-1(m)', 'Sensor-1-2(m)', 'Sensor-3-1(m)', 'Sensor-3-2(m)', 'Sensor-4-1(m)', 'Sensor-4-2(m)', 'Sensor-2-3(m)', 'Sensor-2-4(m)', 'Sensor-1-3(m)', 'Sensor-1-4(m)', 'Sensor-3-3(m)', 'Sensor-3-4(m)', 'Sensor-4-3(m)', 'Sensor-4-4(m)']


In [85]:
import pandas as pd

# Load dataset
df = pd.read_csv("2_em_filtered.csv", header=0)

# Drop first 20 rows and last 20 rows
df_trimmed = df.iloc[20:-20]

# Save the trimmed dataset
df_trimmed.to_csv("2_em_denoised.csv", index=False, float_format="%.6f")

print("Rows removed: first 20 and last 20. Saved as 2_em_denoised.csv")
print(df_trimmed.shape)
print(df_trimmed.dtypes)
print(df_trimmed.columns.tolist())

Rows removed: first 20 and last 20. Saved as 2_em_denoised.csv
(41746, 19)
TimeStart(seconds)    float64
MethConcStart(ppm)    float64
EthyConcStart(ppm)    float64
Sensor-2-1(m)         float64
Sensor-2-2(m)         float64
Sensor-1-1(m)         float64
Sensor-1-2(m)         float64
Sensor-3-1(m)         float64
Sensor-3-2(m)         float64
Sensor-4-1(m)         float64
Sensor-4-2(m)         float64
Sensor-2-3(m)         float64
Sensor-2-4(m)         float64
Sensor-1-3(m)         float64
Sensor-1-4(m)         float64
Sensor-3-3(m)         float64
Sensor-3-4(m)         float64
Sensor-4-3(m)         float64
Sensor-4-4(m)         float64
dtype: object
['TimeStart(seconds)', 'MethConcStart(ppm)', 'EthyConcStart(ppm)', 'Sensor-2-1(m)', 'Sensor-2-2(m)', 'Sensor-1-1(m)', 'Sensor-1-2(m)', 'Sensor-3-1(m)', 'Sensor-3-2(m)', 'Sensor-4-1(m)', 'Sensor-4-2(m)', 'Sensor-2-3(m)', 'Sensor-2-4(m)', 'Sensor-1-3(m)', 'Sensor-1-4(m)', 'Sensor-3-3(m)', 'Sensor-3-4(m)', 'Sensor-4-3(m)', 'Sensor-4-4(m)']


## Vertically Stacked Individual Plots for all Slopes from a Sensor Group

In [86]:
import pandas as pd
import plotly.subplots as sp
import plotly.graph_objects as go

# Define column names explicitly
col_names = [
    "Time(seconds)", 
    "MethConcStart(ppm)",
    "EthyConcStart(ppm)",
    "Sensor-2-1(m)", "Sensor-2-2(m)",
    "Sensor-1-1(m)", "Sensor-1-2(m)", 
    "Sensor-3-1(m)", "Sensor-3-2(m)", 
    "Sensor-4-1(m)", "Sensor-4-2(m)", 
    "Sensor-2-3(m)", "Sensor-2-4(m)", 
    "Sensor-1-3(m)", "Sensor-1-4(m)", 
    "Sensor-3-3(m)", "Sensor-3-4(m)", 
    "Sensor-4-3(m)", "Sensor-4-4(m)", 
]

# Load CSV, skip first 20 rows, assign headers
df = pd.read_csv("2_em_filtered.csv", skiprows=20, header=0, names=col_names)

# Drop the last 20 rows
df = df.iloc[:-20, :]

# Define sensor groups
sensor_groups = {
    "Sensor-1": ["Sensor-1-1(m)", "Sensor-1-2(m)", "Sensor-1-3(m)", "Sensor-1-4(m)"],
    "Sensor-2": ["Sensor-2-1(m)", "Sensor-2-2(m)", "Sensor-2-3(m)", "Sensor-2-4(m)"],
    "Sensor-3": ["Sensor-3-1(m)", "Sensor-3-2(m)", "Sensor-3-3(m)", "Sensor-3-4(m)"],
    "Sensor-4": ["Sensor-4-1(m)", "Sensor-4-2(m)", "Sensor-4-3(m)", "Sensor-4-4(m)"],
}

# 👉 Select which group you want to plot
selected_group = "Sensor-1"   # change to "Sensor-2", "Sensor-3", or "Sensor-4"

time = df["Time(seconds)"]

# Create vertically stacked subplots (one per sensor in the group)
fig = sp.make_subplots(rows=len(sensor_groups[selected_group]), cols=1, shared_xaxes=True,
                       subplot_titles=sensor_groups[selected_group])

# Add traces for each sensor in the selected group
for i, sensor in enumerate(sensor_groups[selected_group], start=1):
    if sensor in df.columns:
        fig.add_trace(
            go.Scatter(x=time, y=df[sensor], mode="lines", name=sensor),
            row=i, col=1
        )

# Update layout
fig.update_layout(height=900, width=1000,
                  title_text=f"{selected_group} Slopes vs Time (Stacked Subplots)",
                  showlegend=True)

# Axis labels
fig.update_xaxes(title_text="Time (seconds)", row=len(sensor_groups[selected_group]), col=1)
for i in range(1, len(sensor_groups[selected_group])+1):
    fig.update_yaxes(title_text="Slope (m)", row=i, col=1)

fig.show()


In [87]:
import pandas as pd
import plotly.subplots as sp
import plotly.graph_objects as go

# Define column names explicitly
col_names = [
    "Time(seconds)", 
    "MethConcStart(ppm)",
    "EthyConcStart(ppm)",
    "Sensor-2-1(m)", "Sensor-2-2(m)",
    "Sensor-1-1(m)", "Sensor-1-2(m)", 
    "Sensor-3-1(m)", "Sensor-3-2(m)", 
    "Sensor-4-1(m)", "Sensor-4-2(m)", 
    "Sensor-2-3(m)", "Sensor-2-4(m)", 
    "Sensor-1-3(m)", "Sensor-1-4(m)", 
    "Sensor-3-3(m)", "Sensor-3-4(m)", 
    "Sensor-4-3(m)", "Sensor-4-4(m)", 
]

# Load CSV, skip first 20 rows, assign headers
df = pd.read_csv("2_em_filtered.csv", skiprows=20, header=0, names=col_names)

# Drop the last 20 rows
df = df.iloc[:-20, :]

# Define sensor groups
sensor_groups = {
    "Sensor-1": ["Sensor-1-1(m)", "Sensor-1-2(m)", "Sensor-1-3(m)", "Sensor-1-4(m)"],
    "Sensor-2": ["Sensor-2-1(m)", "Sensor-2-2(m)", "Sensor-2-3(m)", "Sensor-2-4(m)"],
    "Sensor-3": ["Sensor-3-1(m)", "Sensor-3-2(m)", "Sensor-3-3(m)", "Sensor-3-4(m)"],
    "Sensor-4": ["Sensor-4-1(m)", "Sensor-4-2(m)", "Sensor-4-3(m)", "Sensor-4-4(m)"],
}

# 👉 Select which group you want to plot
selected_group = "Sensor-2"   # change to "Sensor-2", "Sensor-3", or "Sensor-4"

time = df["Time(seconds)"]

# Create vertically stacked subplots (one per sensor in the group)
fig = sp.make_subplots(rows=len(sensor_groups[selected_group]), cols=1, shared_xaxes=True,
                       subplot_titles=sensor_groups[selected_group])

# Add traces for each sensor in the selected group
for i, sensor in enumerate(sensor_groups[selected_group], start=1):
    if sensor in df.columns:
        fig.add_trace(
            go.Scatter(x=time, y=df[sensor], mode="lines", name=sensor),
            row=i, col=1
        )

# Update layout
fig.update_layout(height=900, width=1000,
                  title_text=f"{selected_group} Slopes vs Time (Stacked Subplots)",
                  showlegend=True)

# Axis labels
fig.update_xaxes(title_text="Time (seconds)", row=len(sensor_groups[selected_group]), col=1)
for i in range(1, len(sensor_groups[selected_group])+1):
    fig.update_yaxes(title_text="Slope (m)", row=i, col=1)

fig.show()


In [88]:
import pandas as pd
import plotly.subplots as sp
import plotly.graph_objects as go

# Define column names explicitly
col_names = [
    "Time(seconds)", 
    "MethConcStart(ppm)",
    "EthyConcStart(ppm)",
    "Sensor-2-1(m)", "Sensor-2-2(m)",
    "Sensor-1-1(m)", "Sensor-1-2(m)", 
    "Sensor-3-1(m)", "Sensor-3-2(m)", 
    "Sensor-4-1(m)", "Sensor-4-2(m)", 
    "Sensor-2-3(m)", "Sensor-2-4(m)", 
    "Sensor-1-3(m)", "Sensor-1-4(m)", 
    "Sensor-3-3(m)", "Sensor-3-4(m)", 
    "Sensor-4-3(m)", "Sensor-4-4(m)", 
]

# Load CSV, skip first 20 rows, assign headers
df = pd.read_csv("2_em_filtered.csv", skiprows=20, header=0, names=col_names)

# Drop the last 20 rows
df = df.iloc[:-20, :]

# Define sensor groups
sensor_groups = {
    "Sensor-1": ["Sensor-1-1(m)", "Sensor-1-2(m)", "Sensor-1-3(m)", "Sensor-1-4(m)"],
    "Sensor-2": ["Sensor-2-1(m)", "Sensor-2-2(m)", "Sensor-2-3(m)", "Sensor-2-4(m)"],
    "Sensor-3": ["Sensor-3-1(m)", "Sensor-3-2(m)", "Sensor-3-3(m)", "Sensor-3-4(m)"],
    "Sensor-4": ["Sensor-4-1(m)", "Sensor-4-2(m)", "Sensor-4-3(m)", "Sensor-4-4(m)"],
}

# 👉 Select which group you want to plot
selected_group = "Sensor-3"   # change to "Sensor-2", "Sensor-3", or "Sensor-4"

time = df["Time(seconds)"]

# Create vertically stacked subplots (one per sensor in the group)
fig = sp.make_subplots(rows=len(sensor_groups[selected_group]), cols=1, shared_xaxes=True,
                       subplot_titles=sensor_groups[selected_group])

# Add traces for each sensor in the selected group
for i, sensor in enumerate(sensor_groups[selected_group], start=1):
    if sensor in df.columns:
        fig.add_trace(
            go.Scatter(x=time, y=df[sensor], mode="lines", name=sensor),
            row=i, col=1
        )

# Update layout
fig.update_layout(height=900, width=1000,
                  title_text=f"{selected_group} Slopes vs Time (Stacked Subplots)",
                  showlegend=True)

# Axis labels
fig.update_xaxes(title_text="Time (seconds)", row=len(sensor_groups[selected_group]), col=1)
for i in range(1, len(sensor_groups[selected_group])+1):
    fig.update_yaxes(title_text="Slope (m)", row=i, col=1)

fig.show()


In [89]:
import pandas as pd
import plotly.subplots as sp
import plotly.graph_objects as go

# Define column names explicitly
col_names = [
    "Time(seconds)", 
    "MethConcStart(ppm)",
    "EthyConcStart(ppm)",
    "Sensor-2-1(m)", "Sensor-2-2(m)",
    "Sensor-1-1(m)", "Sensor-1-2(m)", 
    "Sensor-3-1(m)", "Sensor-3-2(m)", 
    "Sensor-4-1(m)", "Sensor-4-2(m)", 
    "Sensor-2-3(m)", "Sensor-2-4(m)", 
    "Sensor-1-3(m)", "Sensor-1-4(m)", 
    "Sensor-3-3(m)", "Sensor-3-4(m)", 
    "Sensor-4-3(m)", "Sensor-4-4(m)", 
]

# Load CSV, skip first 20 rows, assign headers
df = pd.read_csv("2_em_filtered.csv", skiprows=20, header=0, names=col_names)

# Drop the last 20 rows
df = df.iloc[:-20, :]

# Define sensor groups
sensor_groups = {
    "Sensor-1": ["Sensor-1-1(m)", "Sensor-1-2(m)", "Sensor-1-3(m)", "Sensor-1-4(m)"],
    "Sensor-2": ["Sensor-2-1(m)", "Sensor-2-2(m)", "Sensor-2-3(m)", "Sensor-2-4(m)"],
    "Sensor-3": ["Sensor-3-1(m)", "Sensor-3-2(m)", "Sensor-3-3(m)", "Sensor-3-4(m)"],
    "Sensor-4": ["Sensor-4-1(m)", "Sensor-4-2(m)", "Sensor-4-3(m)", "Sensor-4-4(m)"],
}

# 👉 Select which group you want to plot
selected_group = "Sensor-4"   # change to "Sensor-2", "Sensor-3", or "Sensor-4"

time = df["Time(seconds)"]

# Create vertically stacked subplots (one per sensor in the group)
fig = sp.make_subplots(rows=len(sensor_groups[selected_group]), cols=1, shared_xaxes=True,
                       subplot_titles=sensor_groups[selected_group])

# Add traces for each sensor in the selected group
for i, sensor in enumerate(sensor_groups[selected_group], start=1):
    if sensor in df.columns:
        fig.add_trace(
            go.Scatter(x=time, y=df[sensor], mode="lines", name=sensor),
            row=i, col=1
        )

# Update layout
fig.update_layout(height=900, width=1000,
                  title_text=f"{selected_group} Slopes vs Time (Stacked Subplots)",
                  showlegend=True)

# Axis labels
fig.update_xaxes(title_text="Time (seconds)", row=len(sensor_groups[selected_group]), col=1)
for i in range(1, len(sensor_groups[selected_group])+1):
    fig.update_yaxes(title_text="Slope (m)", row=i, col=1)

fig.show()
